<a href="https://colab.research.google.com/github/kumarmaheshbly-oss/Project-Aura-/blob/main/3d_cam_network_simulation.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

In [1]:

import numpy as np
import matplotlib.pyplot as plt
from mpl_toolkits.mplot3d import Axes3D
from matplotlib.animation import FuncAnimation
from IPython.display import HTML

# --- Setup ---
steps = 60
dt = 1.0
time = np.arange(steps)

sat_pos = np.array([0.0, 0.0, 0.0])
debris_pos = np.array([50.0, 50.0, 0.0])
sat_vel = np.array([1.0, 0.0, 0.0])
debris_vel = np.array([-1.0, -1.0, 0.0])

# Link partner (Another satellite for network demo)
link_partner_pos = np.array([0.0, 30.0, 0.0])

sat_traj, deb_traj, link_partner_traj = [], [], []
maneuver_executed = False
delta_v_applied = 0.0

for t in time:
    dist = np.linalg.norm(sat_pos - debris_pos)

    # --- THE UPGRADE: Calculate Delta-V & Trigger Maneuver ---
    if dist < 15.0 and not maneuver_executed:
        # Calculate required Delta-V to increase miss distance
        delta_v_needed = (15.0 - dist) * 0.1 # Simplified calculation
        sat_vel = np.array([0.5, 1.2 + delta_v_needed, 0.0])
        maneuver_executed = True
        delta_v_applied = delta_v_needed
        print(f"🚨 CAM Triggered! Delta-V Applied: {delta_v_applied:.2f} m/s")

    sat_traj.append(sat_pos.copy())
    deb_traj.append(debris_pos.copy())
    link_partner_traj.append(link_partner_pos.copy())

    sat_pos += sat_vel * dt
    debris_pos += debris_vel * dt

sat_traj, deb_traj, link_partner_traj = np.array(sat_traj), np.array(deb_traj), np.array(link_partner_traj)

# --- Animation ---
fig = plt.figure(figsize=(10, 8))
ax = fig.add_subplot(111, projection='3d')
ax.set_xlim(-50, 100); ax.set_ylim(-50, 100); ax.set_zlim(-20, 20)
ax.set_title('Project Aura: CAM with Network Link Disruption', color='white')
fig.patch.set_facecolor('#111111') # Dark space theme
ax.set_facecolor('#111111')
ax.xaxis.label.set_color('white'); ax.yaxis.label.set_color('white'); ax.zaxis.label.set_color('white')
ax.tick_params(colors='white')

sat_dot, = ax.plot([], [], [], 'bo', markersize=8, label='Aura Satellite')
deb_dot, = ax.plot([], [], [], 'ro', markersize=8, label='Space Debris')
link_dot, = ax.plot([], [], [], 'co', markersize=6, label='TLTE Agent Node')

# Link Line (Starts Cyan, turns red on CAM)
link_line, = ax.plot([], [], [], '-', color='cyan', linewidth=2, label='Optical Data Link')
sat_path, = ax.plot([], [], [], 'b-', alpha=0.4)
deb_path, = ax.plot([], [], [], 'r-', alpha=0.4)
ax.legend(loc='upper right', facecolor='black', labelcolor='white')

def update(frame):
    sat_dot.set_data([sat_traj[frame, 0]], [sat_traj[frame, 1]]); sat_dot.set_3d_properties([sat_traj[frame, 2]])
    deb_dot.set_data([deb_traj[frame, 0]], [deb_traj[frame, 1]]); deb_dot.set_3d_properties([deb_traj[frame, 2]])
    link_dot.set_data([link_partner_traj[frame, 0]], [link_partner_traj[frame, 1]]); link_dot.set_3d_properties([link_partner_traj[frame, 2]])

    sat_path.set_data(sat_traj[:frame+1, 0], sat_traj[:frame+1, 1]); sat_path.set_3d_properties(sat_traj[:frame+1, 2])
    deb_path.set_data(deb_traj[:frame+1, 0], deb_traj[:frame+1, 1]); deb_path.set_3d_properties(deb_traj[:frame+1, 2])

    # Update Link Line (Break it if maneuver happens)
    link_line.set_data([sat_traj[frame, 0], link_partner_traj[frame, 0]],
                       [sat_traj[frame, 1], link_partner_traj[frame, 1]])
    link_line.set_3d_properties([sat_traj[frame, 2], link_partner_traj[frame, 2]])

    if maneuver_executed and frame > 20: # Arbitrary frame after CAM
        link_line.set_color('red') # Link breaks
    else:
        link_line.set_color('cyan') # Link active

    return sat_dot, deb_dot, link_dot, link_line, sat_path, deb_path

ani = FuncAnimation(fig, update, frames=steps, interval=100, blit=False)
plt.close()
HTML(ani.to_jshtml())